[![Open In Colab](https://colab.research.google.com/assets/colab-badge.svg)](https://colab.research.google.com/github/jeremydwong/bonelab_inverse_dynamics/blob/main/notebooks/varus_intervention.ipynb)

# Step frequency at a fixed walking speed, measured and time-rescaled: can quicker, shorter steps unload a (varus) knee?

The question people ask: if your knee hurts, or it's bowed (varus) and you're worried about wear on the medial side, should you take quicker, shorter steps? Long steps feel like they should be worse. So this page takes P1 walking at 1.25 m/s and changes only the step frequency, two ways:

1. **Time-rescaled (the cheap way).** Take P1's preferred walk and squeeze or stretch it in time to f<sub>0</sub> &plusmn; 2, 4, &hellip; 10 steps/min, rescaling the forces so the speed stays put. I didn't know if this was legal. (Spoiler: it isn't, really.)
2. **Measured (the honest way).** It turns out van der Zee, Mundinger &amp; Kuo (2022) already did this experiment: P1 walked at 1.25 m/s with a metronome at 0.7&ndash;1.3&times; preferred step frequency. Those trials are sitting in the same file as everything else.

Then both go through OpenSim (static optimization, same model and contact split as the P1 muscle page) to get knee contact, and through our own inverse dynamics for the knee adduction moment, with the knee pushed into varus on top.

**This notebook reports on the following key findings:**

1. **The time-rescale isn't legal for this.** Next to P1's real trials at 95 and 117 steps/min it gets the direction wrong: peak vertical GRF 1.20 / 1.30 BW rescaled vs 1.33 / 1.18 BW measured, and peak knee extension moment 0.57 / 0.98 vs 1.01 / 0.65 N m/kg. Played faster with the same bounce, loads have to go up; P1 actually flattens out and bends the knee less.
2. **Measured, per step: the peak barely moves, the impulse does.** Peak knee contact is 4.8&ndash;5.4 BW anywhere from 95 to 135 steps/min (6.2 BW only at the slowest, 75). Contact impulse per stance falls 47%, 2.98 &rarr; 1.57 BW&middot;s, mostly because the stance gets shorter.
3. **Measured, per km: flat.** Total contact impulse is 1478&ndash;1518 BW&middot;s per km (right leg) from 95 to 135 steps/min, within &plusmn;1.5%; medial is 999&ndash;1038. Only going slow costs anything: 1669 at 75 steps/min (+12%).
4. **The rescale says the opposite of the data per km:** 1479 &rarr; 1543 BW&middot;s/km from f<sub>0</sub>&minus;10 to f<sub>0</sub>+10, and medial 953 &rarr; 1091 (+14%).
5. **A varus knee doesn't get a cadence discount either.** Our knee adduction moment impulse per km is 218&ndash;231 N m&middot;s/kg from 85 to 135 steps/min, and pushing the knee out 25 / 50 mm adds about +44% / +89% at *every* cadence.
6. **The medial/lateral split depends on the contact geometry, the trend doesn't.** Going from 30 to 50 mm between the condyle contacts moves peak medial from 3.98 to 3.43 BW at preferred cadence; the cadence trend is the same at all three.
7. **Two animated walkers** (measured and rescaled) with a slider over step frequency that swaps the walker, its cadence and every synced trace.

In [1]:
# Colab bootstrap: a no-op when running locally. On Colab it clones the repo (for its
# data/ folder), installs boneid from the clone, and runs from notebooks/ so the
# relative paths below work.
import os, sys, subprocess
if "google.colab" in sys.modules and not os.path.exists("../src/boneid"):
    subprocess.run(["git", "clone", "--depth", "1",
                    "https://github.com/jeremydwong/bonelab_inverse_dynamics"], check=True)
    subprocess.run([sys.executable, "-m", "pip", "install", "-q", "-e", "bonelab_inverse_dynamics"], check=True)
    os.chdir("bonelab_inverse_dynamics/notebooks")
os.makedirs("../reports", exist_ok=True)

In [2]:
import json
from pathlib import Path
import numpy as np
from IPython.display import HTML, display

from boneid import io_v3d as io, report as R, simulate as sim
from boneid.core import detect_contact

# The full P1 export (~84 MB) isn't in the repo (it's a GitHub release asset, tag
# data-p1-v1). Point BONEID_V3D_DIR at the folder holding p1_5StridesData.mat.
V3D_DIR = os.environ.get("BONEID_V3D_DIR", "/Users/jeremy/Dropbox/Public/inverse-dynamics-test-data")
P1 = os.path.join(V3D_DIR, "p1_5StridesData.mat")
if not os.path.exists(P1):
    raise FileNotFoundError(f"{P1} isn't there; set BONEID_V3D_DIR to the folder that has it.")

params = R.p1_params()
M = 85.16                      # P1 body mass, kg (same as the OpenSim model)
BW = M * 9.81

def show(fig):
    display(HTML(R.fig_svg(fig)))

# measured fixed-speed trials (0-based slots; van der Zee Table 2 trials 17-25)
SLOTS = [16, 17, 18, 19, 20, 21, 22, 23, 24]
NOMINAL = {16: 0.7, 17: 0.8, 18: 0.9, 19: 1.0, 20: 1.0, 21: 1.0, 22: 1.1, 23: 1.2, 24: 1.3}
trials = {s: io.load_v3d_trial(P1, s) for s in SLOTS}
runs = {s: R.whole_body_run(trials[s], params) for s in SLOTS}

def stride_time(run, rate=120.0):
    st = R.right_strides(run[0])
    return float(np.mean(np.diff(st, axis=1))) / rate

T = {s: stride_time(runs[s]) for s in SLOTS}
V = {s: R.belt_speed(trials[s]) for s in SLOTS}
F0 = 120.0 / T[19]             # slot 19 = the preferred trial the rescale starts from
print(f"preferred step frequency f0 = {F0:.1f} steps/min (slot 19); "
      f"the three preferred trials: {', '.join(f'{120 / T[s]:.1f}' for s in (19, 20, 21))}")
print(" slot  nominal f/f0 | steps/min  stride (s)  belt (m/s)  step length (m)")
for s in SLOTS:
    print(f" {s:4d}  {NOMINAL[s]:12.1f} | {120 / T[s]:9.1f}  {T[s]:10.3f}  {V[s]:10.2f}  {V[s] * T[s] / 2:15.3f}")

preferred step frequency f0 = 106.5 steps/min (slot 19); the three preferred trials: 106.5, 107.9, 104.2
 slot  nominal f/f0 | steps/min  stride (s)  belt (m/s)  step length (m)
   16           0.7 |      75.1       1.598        1.12            0.892
   17           0.8 |      85.5       1.404        1.17            0.821
   18           0.9 |      95.2       1.260        1.17            0.739
   19           1.0 |     106.5       1.127        1.18            0.666
   20           1.0 |     107.9       1.113        1.18            0.656
   21           1.0 |     104.2       1.152        1.18            0.681
   22           1.1 |     116.8       1.027        1.18            0.604
   23           1.2 |     125.2       0.958        1.18            0.565
   24           1.3 |     134.9       0.890        1.16            0.518


## 1. What's out there

Short version: in **running** this has been studied a lot, in **walking** much less, and nobody seems to have used this fixed-speed sweep in the van der Zee data for knee loads. I had an agent check each of these against Europe PMC (title, DOI, PMID); numbers are from abstracts unless noted.

- **Running, per step: quicker steps help.** +10% step rate cut knee energy absorption by about a third (Heiderscheit et al. 2011, *MSSE* 43:296, doi:10.1249/MSS.0b013e3181ebedf4) and peak patellofemoral force by 14% (Lenhart et al. 2014, *MSSE* 46:557, doi:10.1249/MSS.0b013e3182a78c3a). Peak vertical GRF barely moves (&minus;2.5%), so it's a *posture* effect: less knee flexion in stance, less quadriceps.
- **Running, per km: it's a coin toss.** In-field retraining at +7.5% cut peak tibiofemoral and medial contact by about 8% per step, but cumulative load per km didn't change (Willy et al. 2016, *J Sports Sci* 34:1602, doi:10.1080/02640414.2015.1125517). Others find the per-km benefit survives, at about half size (Willson et al. 2015, doi:10.1111/sms.12383; Bowersock et al. 2017, doi:10.1080/02640414.2016.1249904; Willy et al. 2016, *J Biomech* 49:4028, doi:10.1016/j.jbiomech.2016.10.043).
- **Walking, medial knee OA: not much.** At a fixed speed, +2&ndash;10% cadence didn't change the knee adduction moment peak or impulse, and raised impact loading (James et al. 2024, *J Biomech* 177:112394, doi:10.1016/j.jbiomech.2024.112394). Shorter strides lowered KAM impulse per step on average but helped only a third of patients individually (Ulrich et al. 2023, doi:10.1016/j.jbiomech.2023.111449).
- **Per distance is the right bookkeeping**, I think (Miller, Edwards et al. 2014, *MSSE* 46:572, doi:10.1249/MSS.0000000000000135), with the caveat that tissue damage goes up steeply with load per cycle, so fewer big cycles can beat more small ones (Edwards et al. 2009, doi:10.1249/MSS.0b013e3181a984c4).
- **Physics you can't get around:** at a steady speed the vertical impulse per metre is fixed at mg/v, whatever the cadence (Martin &amp; Marsh 1992, doi:10.1016/0021-9290(92)90081-B, found peak vertical GRF barely changes over &plusmn;10% step length). So any per-km benefit has to come from moment arms and muscles, not from the ground force.
- **The data:** van der Zee, Mundinger &amp; Kuo (2022), *Sci Data* 9:704, doi:10.1038/s41597-022-01817-1, Table 2 trials 17&ndash;25 (our slots 16&ndash;24).

## 2. The time-rescale, and whether it's legal

Here's the rule I used (`simulate.step_frequency_trial`). Take the preferred trial, assume time-symmetric gait (left and right steps equal, so step frequency f = 2 / stride time), and pick k = f / f<sub>0</sub>:

- time is compressed: t&prime; = t / k;
- fore&ndash;aft positions (markers and COP) are scaled by 1/k about the treadmill middle, so a stance foot still slides back at belt speed. Step length goes down by 1/k and **speed stays at the belt speed**;
- up&ndash;down and side-to-side positions keep their size;
- forces follow Newton on that motion: accelerations scale by k&sup2; times the spatial scale, so

$$F_z' = mg + k^2\,(F_z - mg),\qquad F_\text{ML}' = k^2 F_\text{ML},\qquad F_\text{AP}' = k\,F_\text{AP}$$

The mean of every force over a stride is unchanged (body weight on average, zero fore&ndash;aft), so it's consistent with steady walking. What it can't do is change *how* P1 walks: the same bounce, the same knee bend, just played faster.

The check is easy because the real thing exists. Slots 18 and 22 are P1 at 95 and 117 steps/min, which is f<sub>0</sub> &minus;11 and +10. So I rescale the preferred trial to exactly those frequencies and compare, using our own inverse dynamics (right leg, per-stance peaks, mean over stances).

In [3]:
from boneid.core import inverse_dynamics

def per_stance(run, rate=120.0):
    chain, whole = run[0], run[3]
    fz = chain[2].force[:, 2]
    _, ev = detect_contact(fz, 20.0, min_gap=5)
    # complete stances only; >= 0.2 s and >= 0.3 BW (slot 17 has a ~20 N belt blip)
    st = [(a, b) for a, b in ev if a > 0 and b < len(fz) - 1 and (b - a) >= 0.2 * rate
          and fz[a:b + 1].max() >= 0.3 * BW]
    tau = whole.right.joint_torque_local
    kam, kext = -tau[:, 1, 0], -tau[:, 1, 1]          # + external adduction, + internal extension
    pk = lambda x: float(np.mean([x[a:b + 1].max() for a, b in st]))
    imp = lambda x: float(np.mean([np.clip(x[a:b + 1], 0, None).sum() / rate for a, b in st]))
    return dict(stance=float(np.mean([(b - a) / rate for a, b in st])), grf=pk(fz) / BW,
                kam=pk(kam) / M, kam_imp=imp(kam) / M, kext=pk(kext) / M, stances=st)

base = trials[19]
SYN_D = list(range(-10, 12, 2))
syn_trials = {d: sim.step_frequency_trial(base, (F0 + d) / F0, M) for d in SYN_D}
syn_runs = {d: R.whole_body_run(syn_trials[d], params) for d in SYN_D}
check = {f"syn@{s}": sim.step_frequency_trial(base, (120 / T[s]) / F0, M) for s in (18, 22)}
check_runs = {k: R.whole_body_run(v, params) for k, v in check.items()}

meas = {s: per_stance(runs[s]) for s in SLOTS}
syn = {d: per_stance(syn_runs[d]) for d in SYN_D}
chk = {k: per_stance(v) for k, v in check_runs.items()}
print("                       steps/min  stance(s)  peak GRF(BW)  peak KAM  KAM impulse  peak knee ext")
print("                                                         (N m/kg)  (N m s/kg)   (N m/kg)")
for lab, r, f in (("measured slot 18", meas[18], 120 / T[18]), ("rescaled to slot 18", chk["syn@18"], 120 / T[18]),
                  ("measured slot 19 (f0)", meas[19], F0),
                  ("measured slot 22", meas[22], 120 / T[22]), ("rescaled to slot 22", chk["syn@22"], 120 / T[22])):
    print(f"{lab:22s} {f:9.1f}  {r['stance']:9.3f}  {r['grf']:12.2f}  {r['kam']:8.2f}  {r['kam_imp']:11.3f}  {r['kext']:12.2f}")

                       steps/min  stance(s)  peak GRF(BW)  peak KAM  KAM impulse  peak knee ext
                                                         (N m/kg)  (N m s/kg)   (N m/kg)
measured slot 18            95.2      0.737          1.33      0.76        0.342          1.01
rescaled to slot 18         95.2      0.763          1.20      0.62        0.276          0.57
measured slot 19 (f0)      106.5      0.682          1.25      0.75        0.297          0.79
measured slot 22           116.8      0.637          1.18      0.73        0.274          0.65
rescaled to slot 22        116.8      0.622          1.30      0.89        0.317          0.98


That's the answer to "is it legal": **no, not for this question.** The rescale gets the *direction* wrong for the things that matter. Played faster with the same bounce, the ground force and the knee extension moment have to go *up* (it's k&sup2; on the dynamic part). But P1 actually walks differently at a higher cadence: flatter, with less knee bend in stance, so the measured peaks go *down*. That matches the running papers, where the whole benefit is posture, and Donelan, Kram &amp; Kuo (2002), where step-to-step collision work goes with step length to the 4th power, so the shape of the force changes, not just its timing. Dynamic similarity doesn't rescue it either: at a fixed speed for one person the Froude number is already fixed, and changing cadence changes the dimensionless step length.

I'll still carry the rescale through the rest of the page, as the "what if the body didn't adapt" case. It's useful as a contrast.

## 3. Knee contact force: per step and per kilometre

OpenSim, same scaled P1 model, IK &rarr; ID &rarr; static optimization &rarr; the two-point medial/lateral plateau split, for all nine measured trials and the eleven rescaled ones (`scripts/opensim/`, see the README there). Contact is in body weights. "Per km" is the right leg's contact impulse per stance times right steps per km (1000 / stride length), so it counts every step that leg takes over a kilometre.

In [4]:
KC = dict(np.load("../data/opensim/p1_stepfreq_knee_contact.npz"))
KJ = json.load(open("../data/opensim/p1_stepfreq_knee_contact.json"))

def contact_series(prefix):
    return {k: KC[f"{prefix}_{k}"] for k in ("total", "medial", "lateral", "lig_lateral")}

def contact_stats(prefix, run, trial, speed):
    c = contact_series(prefix)
    # stances fully inside the static-optimization window (NaN outside it)
    st = [(a, b) for a, b in per_stance(run)["stances"] if np.all(np.isfinite(c["total"][a:b + 1]))]
    T_ = stride_time(run)
    pk = {k: float(np.mean([np.nanmax(c[k][a:b + 1]) for a, b in st])) for k in ("total", "medial", "lateral")}
    imp = {k: float(np.mean([np.nansum(np.clip(c[k][a:b + 1], 0, None)) / trial.rate for a, b in st]))
           for k in ("total", "medial", "lateral")}
    per_km = {k: imp[k] * 1000.0 / (speed * T_) for k in imp}
    return pk, imp, per_km

CS = {s: contact_stats(f"s{s}", runs[s], trials[s], V[s]) for s in SLOTS}
CY = {d: contact_stats(f"syn{d:+d}", syn_runs[d], syn_trials[d], V[19]) for d in SYN_D}
print("                    steps/min | peak contact total/medial/lateral (BW) | impulse/stance (BW s) | per km (BW s/km)")
for s in SLOTS:
    pk, imp, km = CS[s]
    print(f"measured slot {s:2d}  {120 / T[s]:9.1f} | {pk['total']:5.2f} {pk['medial']:5.2f} {pk['lateral']:5.2f}"
          f"                  | {imp['total']:6.3f}              | {km['total']:6.0f} (medial {km['medial']:5.0f})")
for d in SYN_D:
    pk, imp, km = CY[d]
    print(f"rescaled f0{d:+3d}     {F0 + d:9.1f} | {pk['total']:5.2f} {pk['medial']:5.2f} {pk['lateral']:5.2f}"
          f"                  | {imp['total']:6.3f}              | {km['total']:6.0f} (medial {km['medial']:5.0f})")

                    steps/min | peak contact total/medial/lateral (BW) | impulse/stance (BW s) | per km (BW s/km)
measured slot 16       75.1 |  6.24  3.70  2.91                  |  2.978              |   1669 (medial  1158)
measured slot 17       85.5 |  5.07  3.45  2.11                  |  2.543              |   1549 (medial  1033)
measured slot 18       95.2 |  4.83  3.57  1.55                  |  2.185              |   1478 (medial  1038)
measured slot 19      106.5 |  5.24  3.63  1.66                  |  1.993              |   1496 (medial  1011)
measured slot 20      107.9 |  5.16  3.57  1.62                  |  1.939              |   1477 (medial   999)
measured slot 21      104.2 |  5.19  3.63  1.59                  |  2.031              |   1492 (medial  1004)
measured slot 22      116.8 |  5.23  3.58  1.73                  |  1.829              |   1514 (medial  1035)
measured slot 23      125.2 |  5.38  3.56  1.90                  |  1.700              |   1505 (medial  1031

In [5]:
fig, axes = R.new_grid(1, 3, height=3.4, width=12.5)
f_meas = np.array([120 / T[s] for s in SLOTS])
f_syn = np.array([F0 + d for d in SYN_D])
for j, (title, idx, unit) in enumerate((("peak contact per step", 0, "BW"),
                                        ("contact impulse per stance", 1, "BW s"),
                                        ("contact impulse per km, right leg", 2, "BW s / km"))):
    ax = axes[0, j]
    for key, col in (("total", R.NEUTRAL), ("medial", R.JOINT_COLORS[0]), ("lateral", R.JOINT_COLORS[1])):
        ym = np.array([CS[s][idx][key] for s in SLOTS])
        ys = np.array([CY[d][idx][key] for d in SYN_D])
        o = np.argsort(f_meas)
        ax.plot(f_meas[o], ym[o], "o-", color=col, lw=1.8, ms=4, label=f"{key}, measured")
        ax.plot(f_syn, ys, "--", color=col, lw=1.2, label=f"{key}, time-rescaled")
    ax.axvline(F0, color=R.FAINT, lw=1)
    ax.axvspan(F0 - 10, F0 + 10, color=R.FAINT, alpha=0.15, lw=0)
    R.style_axes(ax, "step frequency (steps/min)", unit)
    ax.set_title(title, fontsize=10, color=R.NEUTRAL)
    ax.set_ylim(bottom=0)
axes[0, 0].legend(frameon=False, fontsize=7, ncol=2)
show(fig)

So, per step, faster cadence doesn't lower the *peak* knee contact for P1 (it's about 5.2 BW from 95 to 135 steps/min, and the slow trials are the bad ones), but it does shorten each loading. Per km the two cancel almost exactly: about 1500 BW&middot;s/km whatever the cadence above 95, with the medial side carrying two thirds of it. The rescale (dashed) doesn't match either: its total peak falls steadily (5.57 &rarr; 5.00 BW from f<sub>0</sub>&minus;10 to +10) where the measured one is flat (4.83 at 95, 5.24 at 106, 5.23 at 117 steps/min), and it tilts load onto the medial side as cadence goes up, which the real trials don't do.

(The absolute numbers are about 2&times; what instrumented knees measure, same as on the P1 muscle page; that's static optimization with rigid tendons, see the validation page. I trust the *changes* more than the levels.)

### How much the medial/lateral split hangs on the contact geometry

The split uses two point contacts on a flat plateau, d<sub>ic</sub> = 40.3 mm apart (a generic 40 mm, scaled to P1's tibia). The total doesn't depend on that at all; the medial&minus;lateral *difference* goes like 1/d<sub>ic</sub>. I can redo the split at other spacings without re-running OpenSim: the stored medial, lateral and ligament series give back the raw compressive force F<sub>c</sub> and frontal moment, and then

$$F_\text{med,lat} = \tfrac{1}{2}F_c \pm \frac{M}{d_{ic}}$$

(clamped at zero for lift-off). Here's the peak medial and lateral contact at 30, 40 and 50 mm, measured trials.

In [6]:
D_IC = float(KC["d_ic"])
def resplit(prefix, d_new):
    c = contact_series(prefix)
    raw_lat = c["lateral"] - c["lig_lateral"]          # lift-off clamps lateral; ligament = -raw
    raw_med = c["medial"]                              # (no medial lift-off in these trials)
    fc = raw_med + raw_lat
    m = 0.5 * (raw_med - raw_lat) * D_IC              # frontal moment, BW m
    med = np.clip(0.5 * fc + m / d_new, 0, None)
    lat = np.clip(0.5 * fc - m / d_new, 0, None)
    return med, lat

print(f"d_ic used = {1000 * D_IC:.1f} mm")
print(" slot  steps/min | peak medial (BW) at 30/40/50 mm | peak lateral (BW) at 30/40/50 mm")
sens = {}
for s in SLOTS:
    st = [(a, b) for a, b in per_stance(runs[s])["stances"] if np.all(np.isfinite(KC[f"s{s}_total"][a:b + 1]))]
    row = []
    for d_new in (0.030, D_IC, 0.050):
        med, lat = resplit(f"s{s}", d_new)
        row.append((np.mean([med[a:b + 1].max() for a, b in st]), np.mean([lat[a:b + 1].max() for a, b in st])))
    sens[s] = row
    print(f" {s:4d}  {120 / T[s]:9.1f} | {row[0][0]:5.2f} {row[1][0]:5.2f} {row[2][0]:5.2f}"
          f"                 | {row[0][1]:5.2f} {row[1][1]:5.2f} {row[2][1]:5.2f}")

d_ic used = 40.3 mm
 slot  steps/min | peak medial (BW) at 30/40/50 mm | peak lateral (BW) at 30/40/50 mm
   16       75.1 |  3.98  3.70  3.56                 |  2.87  2.91  2.93
   17       85.5 |  3.78  3.45  3.27                 |  2.06  2.11  2.14
   18       95.2 |  3.97  3.57  3.35                 |  1.41  1.55  1.65
   19      106.5 |  3.98  3.63  3.43                 |  1.35  1.66  1.84
   20      107.9 |  3.91  3.57  3.37                 |  1.31  1.62  1.80
   21      104.2 |  3.98  3.63  3.43                 |  1.36  1.59  1.78
   22      116.8 |  3.91  3.58  3.39                 |  1.47  1.73  1.89
   23      125.2 |  3.88  3.56  3.39                 |  1.66  1.90  2.05
   24      134.9 |  3.70  3.41  3.26                 |  1.68  1.89  2.03


Medial peak goes down and lateral up as the contacts get further apart, by about 0.5 BW across 30&ndash;50 mm, which is the 1/d<sub>ic</sub> you'd expect. The point for this page is that every cadence moves together, so "flat with cadence" doesn't hang on the 40 mm guess.

## 4. The walkers, animated: measured and time-rescaled, with a slider over step frequency

Each viewer shows one stride per condition, and the slider swaps the whole walker *and* sets the playback speed, so each one steps at its real cadence. The traces underneath are the mean over every right stride, on % of the stride (so they line up whatever the cadence), with the preferred trial as the faint dashed line. Top panel is knee contact from OpenSim; the grid is our inverse dynamics: sagittal angle, sagittal torque and the frontal (external adduction) torque for ankle, knee and hip.

First the measured trials. I left out two of the three preferred repeats (they're nearly identical to slot 19), so the slider runs 75 &rarr; 135 steps/min.

In [7]:
def label(f, prefix, stats, extra=""):
    pk, imp, km = stats
    return (f"<b>{f:.0f} steps/min</b> ({f - F0:+.0f} vs preferred){extra}: peak contact "
            f"{pk['total']:.2f} BW (medial {pk['medial']:.2f}, lateral {pk['lateral']:.2f}); "
            f"{km['total']:.0f} BW&middot;s per km")

SHOWN = [16, 17, 18, 19, 22, 23, 24]
conds = [dict(label=label(120 / T[s], f"s{s}", CS[s], f", step {V[s] * T[s] / 2:.2f} m"),
              trial=trials[s], run=runs[s], contact=contact_series(f"s{s}")) for s in SHOWN]
html_m = R.cadence_section_html(conds, ref=SHOWN.index(19), params=params, uid="cadm")

conds_s = [dict(label=label(F0 + d, f"syn{d:+d}", CY[d]), trial=syn_trials[d], run=syn_runs[d],
                contact=contact_series(f"syn{d:+d}")) for d in SYN_D]
html_s = R.cadence_section_html(conds_s, ref=SYN_D.index(0), params=params, uid="cads")

page = R.html_page(
    "Step frequency at 1.25 m/s: knee load per step and per km",
    "cadence",
    "<p class='eyebrow'>boneid &middot; P1 at 1.25 m/s &middot; step-frequency sweep</p>"
    "<h1>Step frequency at 1.25 m/s, measured and time-rescaled: knee load as the steps get quicker</h1>"
    "<h2>Measured: P1 walking to a metronome</h2>" + html_m +
    "<h2>Time-rescaled: P1's preferred walk played at f<sub>0</sub> &plusmn; 2&hellip;10 steps/min</h2>" + html_s)
Path("../reports/varus_intervention_page.html").write_text(page)
display(HTML(page))

## 5. And the varus knee? Push the knee out and change the cadence

Same trick as on the P1 muscle page: move the right knee laterally by d (0, 25, 50 mm), hip, ankle, foot and the measured ground force fixed, and re-run our inverse dynamics on every measured trial. The knee adduction moment (KAM) is the usual stand-in for medial compartment load. Peak and impulse per step, and impulse per km.

In [8]:
DS = [0.0, 0.025, 0.05]
kam_tab = {}
for s in SLOTS:
    chain = runs[s][0]
    ser = R.knee_variant_series(chain, params, DS)
    st = per_stance(runs[s])["stances"]
    pk = [np.mean([ser["frontal"][k][a:b + 1, 1].max() for a, b in st]) / M for k in range(len(DS))]
    imp = [np.mean([np.clip(ser["frontal"][k][a:b + 1, 1], 0, None).sum() / trials[s].rate for a, b in st]) / M
           for k in range(len(DS))]
    kam_tab[s] = (pk, imp, [i * 1000 / (V[s] * T[s]) for i in imp])
print(" slot  steps/min | peak KAM (N m/kg), d = 0 / 25 / 50 mm | KAM impulse per km (N m s/kg/km)")
for s in SLOTS:
    pk, imp, km = kam_tab[s]
    print(f" {s:4d}  {120 / T[s]:9.1f} | {pk[0]:5.2f} {pk[1]:5.2f} {pk[2]:5.2f}                       | "
          f"{km[0]:5.0f} {km[1]:5.0f} {km[2]:5.0f}")

fig, axes = R.new_grid(1, 2, height=3.2, width=12.5)
o = np.argsort(f_meas)
for k, (d, col) in enumerate(zip(DS, (R.NEUTRAL, R.JOINT_COLORS[0], R.JOINT_COLORS[1]))):
    lab = f"knee out {1000 * d:.0f} mm"
    axes[0, 0].plot(f_meas[o], np.array([kam_tab[s][0][k] for s in SLOTS])[o], "o-", color=col, lw=1.8, ms=4, label=lab)
    axes[0, 1].plot(f_meas[o], np.array([kam_tab[s][2][k] for s in SLOTS])[o], "o-", color=col, lw=1.8, ms=4, label=lab)
for ax, title, unit in ((axes[0, 0], "peak KAM per step", "N m/kg"),
                        (axes[0, 1], "KAM impulse per km, right leg", "N m s/kg per km")):
    ax.axvline(F0, color=R.FAINT, lw=1)
    R.style_axes(ax, "step frequency (steps/min)", unit)
    ax.set_title(title, fontsize=10, color=R.NEUTRAL)
    ax.set_ylim(bottom=0)
axes[0, 0].legend(frameon=False, fontsize=8)
show(fig)

 slot  steps/min | peak KAM (N m/kg), d = 0 / 25 / 50 mm | KAM impulse per km (N m s/kg/km)
   16       75.1 |  0.86  1.18  1.51                       |   248   354   461
   17       85.5 |  0.87  1.20  1.54                       |   226   326   428
   18       95.2 |  0.76  1.03  1.32                       |   231   329   428
   19      106.5 |  0.75  1.02  1.31                       |   223   321   420
   20      107.9 |  0.79  1.07  1.34                       |   221   316   413
   21      104.2 |  0.71  0.99  1.29                       |   221   319   418
   22      116.8 |  0.73  0.99  1.26                       |   227   325   423
   23      125.2 |  0.78  1.04  1.31                       |   223   320   418
   24      134.9 |  0.73  0.99  1.25                       |   218   315   412


Per step the peak KAM wanders between 0.71 and 0.87 N m/kg with no clean trend, and per km it's flat (about 220&ndash;230 N m&middot;s/kg, except 248 at the slowest). Bowing the knee scales the whole thing up by the same fraction at every cadence. So for a varus knee, in this data, taking quicker shorter steps doesn't buy anything per km; straightening the knee (or offloading it) is what moves the number. That's in line with James et al. (2024), who found +2&ndash;10% cadence didn't change KAM in people with knee OA.

One honest wrinkle: our KAM is bigger than OpenSim's frontal moment for the same trials (about 64 vs 44 N m at preferred cadence). Ours is in the thigh frame about our knee centre; OpenSim's is in the tibia frame about its model knee, and P1's markers make the knee look about 9&deg; varus to us (see the AFF page). Both go the same way with cadence, which is what this page is about.

## 6. What I take from it, and what I don't trust

- **Don't time-rescale gait to answer a cadence question.** I wanted to know if it was legal. It's physically consistent (Newton is happy, the speed is right), but the answer depends on *how people change their walk* at another cadence, and the rescale holds exactly that fixed. Here it got the sign wrong on the ground force, the knee extension moment and the medial share.
- **Per step vs per km is the whole game.** Quicker steps make each loading shorter, and at a fixed speed you take proportionally more of them. For P1 those cancel to within a couple of percent anywhere above 95 steps/min. That's also roughly what the running literature finds when it does the per-km bookkeeping (Willy et al. 2016 found no per-km change; others find about half the per-step benefit survives).
- **If damage goes with peak load to a high power** (fatigue in bone and probably cartilage), then more cycles at the *same* peak is worse, not better: from 106 to 135 steps/min P1 takes 28% more right steps per km at the same ~5.2 BW peak. So "take quicker steps to save your knee" isn't supported here, and might even be backwards. The slow, long-step end is the clearly bad one (6.2 BW peak, +12% per km at 75 steps/min).
- **What I don't trust:** it's one subject (P1) walking to a metronome, not someone trained into a new cadence. The contact levels are 2&times; in vivo. The medial/lateral split is a two-point model. Static optimization doesn't know about co-contraction, which may well change with cadence. And the varus part is our kinematic counterfactual, not a person with a varus knee.
- **What would settle it:** the same sweep in all nine subjects (the data are there, it's about 20 min of OpenSim per subject), and ideally an instrumented-knee dataset with cadence varied.